In [1]:
import sumolib
from shapely.geometry import LineString
import geopandas as gpd

net = sumolib.net.readNet("../data/processed/usaquen_3d_v2.net.xml")  

registros = []
for edge in net.getEdges():
    shape_xy = edge.getShape()
    shape_lonlat = [net.convertXY2LonLat(x, y) for x, y in shape_xy]
    registros.append({
        "edge_id": edge.getID(),
        "geometry": LineString(shape_lonlat)
    })

gdf_sumo = gpd.GeoDataFrame(registros, geometry="geometry", crs="EPSG:4326")

In [2]:
import osmnx as ox

G_osm = ox.graph_from_place("Usaquén, Bogotá, Colombia", network_type="all", simplify=False)
gdf_osm = ox.graph_to_gdfs(G_osm, nodes=False, edges=True).reset_index()

In [5]:
import folium

centro = [gdf_sumo.geometry.centroid.y.mean(), gdf_sumo.geometry.centroid.x.mean()]
m = folium.Map(location=centro, zoom_start=14, tiles="cartodbpositron")

folium.GeoJson(
    gdf_osm, name="OSM original",
    style_function=lambda x: {"color": "red", "weight": 1.5, "opacity": 0.6}
).add_to(m)

folium.GeoJson(
    gdf_sumo, name="Red SUMO",
    style_function=lambda x: {"color": "blue", "weight": 1.5, "opacity": 0.6}
).add_to(m)

folium.LayerControl().add_to(m)
m.save("../data/processed/comparacion_sumo_osm.html")
m

C:\Users\USUARIO\AppData\Local\Temp\ipykernel_11256\1663403893.py:3: UserWarning: Geometry is in a geographic CRS. Results from 'centroid' are likely incorrect. Use 'GeoSeries.to_crs()' to re-project geometries to a projected CRS before this operation.

  centro = [gdf_sumo.geometry.centroid.y.mean(), gdf_sumo.geometry.centroid.x.mean()]


In [ ]:
gdf_osm_m = gdf_osm.to_crs(3116)
gdf_sumo_m = gdf_sumo.to_crs(3116)

buffer_osm = gdf_osm_m.buffer(15).union_all()  #15 m de tolerancia

gdf_sumo_m["fuera_tolerancia"] = ~gdf_sumo_m.geometry.within(buffer_osm)
pct_fuera = gdf_sumo_m.loc[gdf_sumo_m["fuera_tolerancia"], "geometry"].length.sum() / gdf_sumo_m.geometry.length.sum() * 100

print(f"% longitud de red SUMO fuera de tolerancia de 15m: {pct_fuera:.2f}%")

% longitud de red SUMO fuera de tolerancia de 15m: 7.70%


In [6]:
#Aristas fuera de tolerancia, ordenadas por longitud 
problematicas = (
    gdf_sumo_m.loc[gdf_sumo_m["fuera_tolerancia"]]
    .assign(longitud_m=lambda d: d.geometry.length)
    .sort_values("longitud_m", ascending=False)
)

#Exportar como shapefile/GeoJSON para cargar como capa de referencia en NetEdit
problematicas.to_crs(4326).to_file("../data/processed/aristas_revisar.geojson", driver="GeoJSON")

print(problematicas[["edge_id", "longitud_m"]].head(20))

            edge_id   longitud_m
3657     -212877644  5211.229166
25418     889085760  5207.426554
20039     405331159  4588.635256
9909     1033331044  4585.032797
24753     881740472  3551.004974
6575     -881740472  3550.804490
18216     214847405  2366.286596
3651   -212860741#0  2109.321295
18179   212860741#0  2104.620821
21556   586430316#5  1988.036439
5624   -586430316#5  1983.445205
24840     887085496  1479.278464
6649     -887085496  1478.621764
2320   -124004076#1  1248.445853
13902   124004076#1  1240.713964
16467    1422333187  1194.363692
21601    59282499#0  1132.366595
5646    -59282499#0  1128.050708
21602    59282499#1   979.277985
5647    -59282499#1   977.826345


In [7]:
nodos_residuales = ['8248717779', '735100177', '8265723019', '2242482128', '2240220063', '9428061983', '5005727130', '8248663696', '8248735900']  

edges_afectados = [e for e in net.getEdges() 
                    if e.getFromNode().getID() in nodos_residuales 
                    or e.getToNode().getID() in nodos_residuales]

ids_afectados = {e.getID() for e in edges_afectados}
interseccion = set(problematicas["edge_id"]) & ids_afectados
print(f"Aristas problemáticas que coinciden con nodos residuales: {len(interseccion)}")

Aristas problemáticas que coinciden con nodos residuales: 10


In [8]:
ids_largas = problematicas.head(20)["edge_id"].tolist()

for eid in ids_largas:
    e = net.getEdge(eid)
    print(eid, "| tipo:", e.getType(), "| carriles:", e.getLaneNumber(), 
          "| desde:", e.getFromNode().getID(), "| hasta:", e.getToNode().getID())

-212877644 | tipo: highway.path | carriles: 1 | desde: 8265723019 | hasta: 325232379
889085760 | tipo: highway.path | carriles: 1 | desde: 325232379 | hasta: 8265723019
405331159 | tipo: highway.service | carriles: 1 | desde: 482790210 | hasta: 1895761699
1033331044 | tipo: highway.service | carriles: 1 | desde: 1895761706 | hasta: 268153008
881740472 | tipo: highway.cycleway | carriles: 1 | desde: 8265107442 | hasta: 9889896927
-881740472 | tipo: highway.cycleway | carriles: 1 | desde: 9889896927 | hasta: 8265107442
214847405 | tipo: highway.bridleway | carriles: 1 | desde: 1037432617 | hasta: 2243152443
-212860741#0 | tipo: highway.track | carriles: 1 | desde: 5603144341 | hasta: 735089729
212860741#0 | tipo: highway.track | carriles: 1 | desde: 735089729 | hasta: 5603144341
586430316#5 | tipo: highway.unclassified | carriles: 1 | desde: cluster_1149890372_8248663624 | hasta: 478324643
-586430316#5 | tipo: highway.unclassified | carriles: 1 | desde: 478324643 | hasta: cluster_1149890

In [9]:
from shapely.ops import nearest_points

def pct_vertices_fuera(gdf_sumo_m, buffer_osm, tolerancia=15):
    total_v, fuera_v = 0, 0
    for geom in gdf_sumo_m.geometry:
        for x, y in geom.coords:
            total_v += 1
            if not buffer_osm.contains(gpd_point := __import__("shapely.geometry", fromlist=["Point"]).Point(x, y)):
                fuera_v += 1
    return fuera_v / total_v * 100

print(f"% vértices fuera de tolerancia: {pct_vertices_fuera(gdf_sumo_m, buffer_osm):.2f}%")

% vértices fuera de tolerancia: 5.34%


In [11]:
tipos_prioritarios = ["highway.service", "highway.unclassified", "highway.residential", 
                       "highway.tertiary", "highway.secondary", "highway.primary"]

problematicas["tipo"] = problematicas["edge_id"].apply(lambda eid: net.getEdge(eid).getType())
revisar_ahora = problematicas[problematicas["tipo"].isin(tipos_prioritarios)]

revisar_ahora.to_crs(4326).to_file("../data/processed/aristas_revisar_prioritarias.geojson", driver="GeoJSON")
print(f"Aristas a revisar manualmente: {len(revisar_ahora)} de {len(problematicas)} totales")

Aristas a revisar manualmente: 201 de 530 totales


## Validación Red SUMO vs. Red OSM original

**Objetivo:** cuantificar la desviación geométrica introducida por `netconvert` en la conversión de OSM a SUMO, y aislar las aristas que requieren corrección manual en NetEdit.

### Resultados

- **% longitud fuera de tolerancia (buffer 15 m):** 7.70%
- **% vértices fuera de tolerancia:** 5.34%
- **Aristas a revisar manualmente (tipos vehiculares):** 201 de 530 totales fuera de tolerancia

### Interpretación

La diferencia entre el % por longitud y el % por vértices indica que buena parte de la desviación se concentra en vías no motorizadas (`path`, `track`, `bridleway`, `cycleway`) de zonas rurales/cerros orientales, donde `netconvert` simplifica la geometría por su baja prioridad para el modelo vehicular. Esto es comportamiento esperado y **no requiere corrección** en el alcance actual (Fase 3, sin bicicletas/peatones aún formalizadas).

Las 201 aristas restantes corresponden a tipos con relevancia vehicular (`service`, `unclassified`, `residential`, `tertiary`, `secondary`, `primary`) y sí deben revisarse contra la red OSM de referencia.

### Archivos de salida (`data/processed/`)

| Archivo | Contenido |
|---|---|
| `comparacion_sumo_osm.html` | Mapa folium con superposición OSM (rojo) vs. SUMO (azul) |
| `aristas_revisar.geojson` | Las 530 aristas fuera de tolerancia (todos los tipos) |
| `aristas_revisar_prioritarias.geojson` | Las 201 aristas vehiculares a corregir manualmente |

### Tareas para Felipe y Samuel (validación manual de red, F2.5)

1. **Cargar la capa de referencia en NetEdit**
   - Abrir `usaquen_3d_v2.net.xml` en NetEdit.
   - Ir a `View → Decals` (o cargar como capa GeoJSON de fondo) y añadir `aristas_revisar_prioritarias.geojson`.
   - Esto muestra únicamente las 201 aristas problemáticas superpuestas sobre la red actual.

2. **Revisar cada arista marcada**
   - Comparar el trazado SUMO contra la geometría OSM de referencia (visible en `comparacion_sumo_osm.html` como respaldo).
   - Priorizar por longitud: las aristas con mayor desviación en metros (ver columna `longitud_m` en `aristas_revisar_prioritarias.geojson`) tienen más impacto en el escenario.

3. **Tipos de corrección esperados**
   - Ajuste de geometría (nodos intermedios faltantes o desplazados).
   - Verificación de conectividad en nodos residuales generados por `netconvert` (10 de las 20 aristas más largas coinciden con estos nodos).
   - Confirmar que el tipo de vía (`highway.*`) asignado sea coherente con `PRIORIDAD_HIGHWAY`.